# XGBoost classification of total corners — all features + grid search

## Goal
Predict the **exact total corner count as a class**, keeping every feature from notebook 19. Compare unweighted, mildly balanced and fully balanced fits within chronological training-only model selection. Inspect the final held-out matches with **±2 corners tolerance**.

This notebook is a configured experiment, not a claim of improved forecasting. The configured all-league candidate grid has **not been executed during preparation**. A bounded synthetic copy is used to verify the complete pipeline. Run All here launches the real grid; CPU is the default and CUDA is opt-in.

## Setup
Use the existing project environment with XGBoost, sklearn, Plotly and notebook dependencies. Launch from this repository. Artifact reuse is enabled; a changed fitting configuration still requires fitting.

In [1]:
from pathlib import Path
import json
import sys
import numpy as np
import pandas as pd
import plotly.graph_objects as go
from IPython.display import display

ROOT = next((p for p in (Path.cwd(), *Path.cwd().parents)
            if (p / "src" / "xdiyo_analytics").is_dir()), None)
if ROOT is None:
    raise RuntimeError("Open this notebook from the xDiyo repository.")
for directory in (ROOT, ROOT / "src"):
    if str(directory) not in sys.path:
        sys.path.insert(0, str(directory))

from notebooks.helpers.classifier_corners import (
    prepare, run_classifier, build_candidates, inner_plan, STAT_CHOICES, HALF_KEYS,
)
from xdiyo_analytics.splits import TemporalSplit
from xdiyo_analytics.training import load_model

from xdiyo_analytics.features import SeededEMA, Hard
from xdiyo_analytics.ratings import GlickoTransition


### Data, all-feature configuration and compute budget
The feature settings below exactly match notebook 19: 22 statistic families, all/half periods, for/against lags, means/std/z-scores/EMA, league/LOO/H2H, standings, Glicko, rest, home–away sums/differences, trends, calendar and league indicators. The same `prepare()` function performs construction; no missing/constant-column preparation filter is applied; optional fitted correlation selection is configured below.

The grid size is calculated from your configured lists (currently 54 combinations). Change its lists to change the budget. `n_estimators` is tuned explicitly; native early stopping and a separate validation tail are disabled. Thus unseen validation classes cannot expand the fit's class universe.

In [2]:
DATA_ROOT = ROOT / "data" / "xDiyo_data"
OUTPUT_ROOT = ROOT / "experiments" / "total_corners_xgboost_classifier"
SEASONS = ("20_21", "21_22", "22_23", "23_24", "24_25")
LEAGUES = None

FEATURE_WINDOWS = (3, 5, 10, 20)
FEATURE_LAGS = (1, 2, 3)
FEATURE_EMA_SPANS = (5, 10)
FEATURE_PERIODS = ("ALL", "1ST", "2ND")
INCLUDE_RATINGS = True
CUTOFF_HOURS = None

DEVICE = "cpu"  # explicit opt-in: "cuda:0" on a capable XGBoost installation
THREADS = 4
REUSE_RESULTS = True
SHOW_PRE_ANALYSIS = True
MODEL_OPTIONS = dict(
    n_estimators=400, learning_rate=0.04, max_depth=3,
    min_child_weight=10, subsample=0.8, colsample_bytree=0.65,
    reg_alpha=0.2, reg_lambda=10.0, max_bin=128,
    early_stopping_rounds=None, random_state=42,
)
GRID = dict(
    max_depth=[2, 3],
    min_child_weight=[20, 30, 60],
    n_estimators=[100, 150, 200],
    balance_power=[0.0, 0.05, 0.1],
)
INNER_SPLITTER = TemporalSplit(train_size=1, test_size=1, unit="seasons",
    calendar_by=(), block_by=("source_season",))
MAX_PLOT_MATCHES = 300
TOP_GAIN_FEATURES = 30

print(f"Grid: {len(build_candidates(model_options=MODEL_OPTIONS, grid=GRID))} candidates")
print(f"Device: {DEVICE}; one active fitting job; {THREADS} estimator threads")
display(pd.DataFrame(STAT_CHOICES, columns=["group", "statistic"]))
print("Half-period keys:", ", ".join(HALF_KEYS))

# Population features: retain old mean3/mean5 and add spread/Z-score + window10.
INCLUDE_LOO = True
LOO_WINDOWS = (3, 5, 10)  # completed league rounds; remove own contributions after selecting the window
LOO_REDUCERS = ("mean", "std", "z")
INCLUDE_H2H = True
H2H_WINDOWS = (3, 5, 10)  # previous encounters for this ordered team/opponent pair
H2H_REDUCERS = ("mean", "std", "z")

# Append warm:: variants; every ordinary baseline stays available. None disables a policy.
WARM_FEATURE_POLICY = SeededEMA(alpha=0.5, handoff=Hard(rounds=1), league_weight=0.5)
WARM_STAT_KEYS = None  # all eligible rolling stats; e.g. ("cornerKicks",) restricts warm variants
WARM_RATING_POLICY = GlickoTransition(
    phi_scale=1.1, movement_phi_scale=1.0, shrinkage=0.5,
    top=3, bottom=3, rank_by="standings", aggregate="mean",
)
# Optional documented team-season predecessor/movement records and explicit entry dates.
# Without these, retained teams are inferred; promotion/relegation is not guessed.
TEAM_SEASONS = None
SEASON_STARTS = None

# Optional fitted selection: None retains every input; e.g. 0.8 requests ceil(80% × inputs).
FEATURE_SELECTION_PROPORTION = None
FEATURE_SELECTION_CORRELATION = "spearman"  # "pearson" or "kendall" also supported
print("Feature selection:", FEATURE_SELECTION_PROPORTION, FEATURE_SELECTION_CORRELATION)


Grid: 54 candidates
Device: cpu; one active fitting job; 4 estimator threads


,group,statistic
0,Match overview,cornerKicks
1,Match overview,ballPossession
2,Match overview,totalShotsOnGoal
3,Match overview,expectedGoals
4,Match overview,bigChanceCreated
5,Match overview,goalkeeperSaves
6,Match overview,totalTackle
7,Shots,shotsOnGoal
8,Shots,shotsOffGoal
9,Shots,blockedScoringAttempt


Half-period keys: cornerKicks, ballPossession, totalShotsOnGoal, shotsOnGoal, shotsOffGoal, touchesInOppBox


## Steps
### 1. Prepare exactly the same historical features
The latest loaded season is the untouched outer test; all preceding loaded seasons form development data. With the selected five seasons, development is 20_21 through 23_24 and the holdout is 24_25. The configured expanding inner splitter evaluates 21_22, 22_23 and 23_24 after training on their preceding seasons (three folds). The winner then fits all four development seasons. Changing SEASONS automatically updates the outer population; INNER_SPLITTER remains independently configurable. Histories follow existing time eligibility; early held-out results can enter later historical features under that retrospective protocol.

### Key assumptions
- A class is the observed nonnegative integer total, not a binned or rescaled label.
- Each fit discovers count classes and prevalence only from its optimization labels. Sparse values such as 3, 7 and 12 remain those counts in public outputs.
- For class count $n_c$, fitting size $N$, and $K$ fitting classes, raw weights are $(N/(Kn_c))^p$, then normalized to mean one over fitting rows. Power $p=0$ is unweighted, $0.5$ mild, and $1$ inverse frequency.
- Class weighting changes the learned probabilities; they are not automatically calibrated betting probabilities. No odds or stakes are fabricated.

In [3]:
bundle = prepare(
    DATA_ROOT, seasons=SEASONS, leagues=LEAGUES,
    windows=FEATURE_WINDOWS, lags=FEATURE_LAGS, spans=FEATURE_EMA_SPANS,
    periods=FEATURE_PERIODS, include_ratings=INCLUDE_RATINGS,
    cutoff_hours=CUTOFF_HOURS,
    include_loo=INCLUDE_LOO, loo_windows=LOO_WINDOWS, loo_reducers=LOO_REDUCERS,
    include_h2h=INCLUDE_H2H, h2h_windows=H2H_WINDOWS, h2h_reducers=H2H_REDUCERS,
    warm_policy=WARM_FEATURE_POLICY, warm_stat_keys=WARM_STAT_KEYS,
    rating_warm_policy=WARM_RATING_POLICY,
    team_seasons=TEAM_SEASONS, season_starts=SEASON_STARTS,
)
dataset = bundle.prepared.dataset
outer = bundle.prepared.split_plan.folds[0]
selection_plan = inner_plan(bundle.prepared, INNER_SPLITTER)
print(f"{len(bundle.definitions):,} historical expressions; {dataset.X.shape[1]:,} retained inputs")
print(f"{len(dataset.X):,} labelled matches; outer train {len(outer.train):,}; outer test {len(outer.test):,}")
display(bundle.data_summary)
display(pd.DataFrame([dict(fold=i, fit_rows=len(f.train), score_rows=len(f.score),
    train_start=dataset.metadata.iloc[f.train].kickoff_at.min(),
    train_end=dataset.metadata.iloc[f.train].kickoff_at.max(),
    score_start=dataset.metadata.iloc[f.score].kickoff_at.min(),
    score_end=dataset.metadata.iloc[f.score].kickoff_at.max())
    for i, f in enumerate(selection_plan.folds)]))

display(bundle.feature_manifest.groupby(["variant", "family"]).size().rename("inputs"))


Loading season tables...
Development seasons: ('20_21', '21_22', '22_23', '23_24'); held out: 24_25
Evaluating 601 historical expressions on 46,978 team rows...
  Historical expressions: 64/601
  Historical expressions: 128/601
  Historical expressions: 192/601
  Historical expressions: 256/601
  Historical expressions: 320/601
  Historical expressions: 384/601
  Historical expressions: 448/601
  Historical expressions: 512/601
  Historical expressions: 576/601
  Historical expressions: 601/601
Prepared 23,486 matches and 1,589 features in 235.0s.
601 historical expressions; 1,589 retained inputs
23,486 labelled matches; outer train 18,886; outer test 4,600


,source_league,source_season,matches
0,Bundesliga,20_21,306
1,Bundesliga,21_22,305
2,Bundesliga,22_23,306
3,Bundesliga,23_24,306
4,Bundesliga,24_25,305
...,...,...,...
60,Serie_B,20_21,379
61,Serie_B,21_22,380
62,Serie_B,22_23,380
63,Serie_B,23_24,380


,fold,fit_rows,score_rows,train_start,train_end,score_start,score_end
0,0,4765,4750,2020-08-01 11:30:00+00:00,2021-05-30 19:00:00+00:00,2021-07-23 18:30:00+00:00,2022-05-29 18:00:00+00:00
1,1,9515,4767,2020-08-01 11:30:00+00:00,2022-05-29 18:00:00+00:00,2022-07-15 18:30:00+00:00,2023-06-04 19:00:00+00:00
2,2,14282,4604,2020-08-01 11:30:00+00:00,2023-06-04 19:00:00+00:00,2023-07-28 18:30:00+00:00,2024-06-02 19:00:00+00:00


### 2. Inspect feature and class coverage
This preview uses the outer training population. The actual balance weights are recomputed independently within each candidate fold. Missing inputs remain missing for native XGBoost handling.

### LOO, H2H and warm starts
LOO/H2H corner means at windows 3/5 already existed. The visible settings extend them to mean/std/Z-score at 3/5/10. LOO excludes the focal team's contributions from completed-round league samples without refilling the window; its Z-score reference is the team's latest eligible corner count. H2H uses prior encounters, separately for/against.

`warm::` columns supplement all ordinary rolling baselines: previous-season priors seed EMA mean/variance and hand off after one completed league round. No eligible prior means ordinary history, including missing values on the first match. Both Glicko streams also get separate transitioned variants. These are historical feature/rating warm starts, not XGBoost optimizer continuation. Only documented movement records enable cross-league promotion/relegation transfers; missing movement evidence is not guessed.

The run configuration records policies/population choices and the manifest identifies baseline/warm families. Set either warm policy to `None` for an unwarmed comparison run. Existing outputs may reflect a previous configuration; restart the kernel and rerun after changing these settings.


In [4]:
assert list(bundle.feature_manifest.feature) == list(dataset.X.columns)
display(bundle.feature_manifest.sort_values("training_nonmissing_fraction").head(20))
print("Retained all-missing training columns:", int((bundle.feature_manifest.training_nonmissing_fraction == 0).sum()))
display(dataset.y.iloc[outer.train, 0].value_counts().sort_index().rename("training_matches").to_frame())


,feature,training_nonmissing_fraction,training_unique_values
585,home::ALL_Defending_errorsLeadToShot_against_z5,0.000212,3
573,home::ALL_Defending_errorsLeadToShot_for_z5,0.000371,4
1177,away::ALL_Defending_errorsLeadToShot_for_z5,0.000477,4
1189,away::ALL_Defending_errorsLeadToShot_against_z5,0.000477,5
1187,away::ALL_Defending_errorsLeadToShot_against_std5,0.002118,4
1175,away::ALL_Defending_errorsLeadToShot_for_std5,0.002118,5
583,home::ALL_Defending_errorsLeadToShot_against_std5,0.002224,4
571,home::ALL_Defending_errorsLeadToShot_for_std5,0.002224,5
1461,difference::ALL_Defending_errorsLeadToShot_aga...,0.002912,4
1457,difference::ALL_Defending_errorsLeadToShot_for...,0.002912,6


Retained all-missing training columns: 0


,training_matches
total_corners,
1.0,14
2.0,89
3.0,268
4.0,537
5.0,880
6.0,1410
7.0,1881
8.0,2101
9.0,2247


### 3. Tune, fit the winner and save the report
Selection minimizes **MAE of the predicted count**, with MSE and accuracy retained for candidate comparison. No test labels select a candidate. The final report adds macro-F1 and an interactive MatchResultReporter using numeric ±2 tolerance.

This cell launches the grid. Completed candidate artifacts can be recovered on rerun; an incomplete XGBoost fit is restarted. After selection, the winner's outer training fit is a separate fit. The final fitted model is saved for later use.

Optional correlation selection is fitted independently inside each candidate's inner training fold and refitted on the winner's outer training population. `None` keeps all inputs. A proportion requests `ceil(proportion × input count)` ranked by absolute correlation; undefined correlations can reduce the retained count. `1.0` keeps all rankable inputs, while `None` also keeps nonrankable inputs. Spearman exploration and the top-30 importance plot do not select features. Exact selected names are saved in `classifier_summary/selected_features.csv`; candidate/fold selections are retained in their fitted reports.


In [5]:
trial = run_classifier(
    bundle, OUTPUT_ROOT, model_options=MODEL_OPTIONS, grid=GRID,
    device=DEVICE, threads=THREADS, reuse=REUSE_RESULTS,
    splitter=INNER_SPLITTER, pre_analysis=SHOW_PRE_ANALYSIS,
    feature_selection_proportion=FEATURE_SELECTION_PROPORTION,
    feature_selection_correlation=FEATURE_SELECTION_CORRELATION,
)
print("Artifacts:", trial.output_path)
print("Reused final result:", trial.result.reused)
display(trial.comparison.head(24))

display(pd.DataFrame([dict(fold=i, available=len(dataset.X.columns),
    selected=len(f.feature_columns), proportion=len(f.feature_columns)/len(dataset.X.columns))
    for i, f in enumerate(trial.result.training.folds)]))


54 candidates × 3 inner fold(s), then one outer fit; 1,589 features.
Artifacts: c:\Users\luisi\Documents\Programming\Python\xDiyo\experiments\total_corners_xgboost_classifier\total-corners-xgboost-classifier-all-features--dc32754e\runs\e5d7db17-146f-4152-937b-b846f161f187\classifier_summary
Reused final result: False


,run_id,name,config_hash,status,comparison_group,score,raw::mae,rank,utility::mae,contribution::mae,selected,candidate_order,saved_run_id,error
0,168f5e8a-2278-4871-898b-eb47587cbc6f,"XGB count 7: max_depth=2, min_child_weight=60,...",c690eadc79f0091f34cf6d2577f12fda0105da12370345...,ranked,01ee626b18cb5bb850779fd73a9ffca5ae938354ccbf87...,1.000000,2.734013,1.0,1.000000,1.000000,True,6,d47f9d1a-8f5c-4e44-97d4-7c8bccbbee9a,None
1,8d07e2f2-61a2-4c67-b698-fedb8d3f4efd,"XGB count 4: max_depth=2, min_child_weight=30,...",5810b1bce9bccdb4ba525860fb1a3f9a20f59cb77359ab...,ranked,01ee626b18cb5bb850779fd73a9ffca5ae938354ccbf87...,0.981132,2.736563,2.0,0.981132,0.981132,False,3,ddf69b5b-edc4-4316-ad0a-d94a9b468bf3,None
2,122d2db5-f216-48e4-b447-aee5f39627c1,"XGB count 25: max_depth=2, min_child_weight=60...",785afca4019892f41b91ca32cd7c05fef54f762113bf34...,ranked,01ee626b18cb5bb850779fd73a9ffca5ae938354ccbf87...,0.962264,2.742582,3.0,0.962264,0.962264,False,24,218d3573-b1e8-447c-a89e-e992ec86ef9d,None
3,8605ae29-204b-41db-92a6-7c3571d40232,"XGB count 1: max_depth=2, min_child_weight=20,...",beb13d76b8fe30bb5d68be6435f0b274929e154756fea2...,ranked,01ee626b18cb5bb850779fd73a9ffca5ae938354ccbf87...,0.943396,2.743219,4.0,0.943396,0.943396,False,0,fdbae11c-4007-4e12-baae-e906a9e58e8b,None
4,56063e66-fb09-47a6-affc-79a75b279117,"XGB count 43: max_depth=2, min_child_weight=60...",440c3d92a9935f8f97c564b5e353a192f2460ee25de6c1...,ranked,01ee626b18cb5bb850779fd73a9ffca5ae938354ccbf87...,0.924528,2.746264,5.0,0.924528,0.924528,False,42,1d7889f2-2ca8-428f-9d61-92728f346d9c,None
5,b02a4ef6-de3a-4fcd-9e43-ccfbac1853b5,"XGB count 22: max_depth=2, min_child_weight=30...",eb5ce2e64790608b135c1eb59d76ec6c16e108371a815b...,ranked,01ee626b18cb5bb850779fd73a9ffca5ae938354ccbf87...,0.905660,2.747043,6.0,0.905660,0.905660,False,21,a388cc3e-e3d3-4311-922f-69cd498545e6,None
6,b4696110-ed3c-443a-aa78-ff585948c4e5,"XGB count 19: max_depth=2, min_child_weight=20...",a7c66c008f9aa607274b56a5371248e2145b117b56eb9e...,ranked,01ee626b18cb5bb850779fd73a9ffca5ae938354ccbf87...,0.886792,2.751646,7.0,0.886792,0.886792,False,18,0ff3fde4-a225-41c0-96f6-fab02c19c68d,None
7,41cd7117-aeb1-4eca-b448-87cf87b4941c,"XGB count 37: max_depth=2, min_child_weight=20...",70b44db9d89b781f7756be550b8bfeeaea7d5daf6eb182...,ranked,01ee626b18cb5bb850779fd73a9ffca5ae938354ccbf87...,0.867925,2.752071,8.0,0.867925,0.867925,False,36,64c48e3e-11fa-4701-847b-d1f549924820,None
8,6053ce50-c83c-4c2f-8b58-ab9819dc8049,"XGB count 40: max_depth=2, min_child_weight=30...",8639124d0eb3250170ac1493530fd39d77e3f9e34ae03d...,ranked,01ee626b18cb5bb850779fd73a9ffca5ae938354ccbf87...,0.849057,2.760782,9.0,0.849057,0.849057,False,39,ffac1c80-704a-4fa5-8e37-69ce5bbcb70c,None
9,0cb4f683-fb66-4525-9e7f-11c28f2dfd42,"XGB count 16: max_depth=3, min_child_weight=60...",a76d0c3df95817479e8cb5b87b2a794ea0e09630bc41bb...,ranked,01ee626b18cb5bb850779fd73a9ffca5ae938354ccbf87...,0.830189,2.761773,10.0,0.830189,0.830189,False,15,fca45895-1fbf-4f92-b97b-49ba69f1dd12,None


## Checks and results
### Held-out quality and unsupported count classes
Every actual test count is retained, including values absent from fitting. Such a value has zero probability under this classifier's learned class set and counts as an ordinary error. The standard selection/report metrics include all rows.

The diagnostic log loss is explicitly floored at $10^{-12}$; `exact_log_loss_infinite` marks zero-probability actual outcomes. `log_loss_supported_only` is supplementary and has a smaller scope when classes are unseen. No standard all-row log-loss claim silently removes unsupported truths.

In [6]:
display(trial.metrics)
display(trial.by_league)
display(trial.class_balance)
display(trial.predictions.loc[~trial.predictions.target_in_fitted_classes,
    ["observed_total_corners", "predicted_total_corners", "observed_class_probability"]].head(20))
display(trial.probabilities.head(10))


,n,mae,mse,accuracy,macro_f1,within_two,unseen_count_rows,unseen_count_fraction,log_loss_clipped_all,log_loss_floor,log_loss_supported_only,exact_log_loss_infinite,baseline_majority_count,baseline_mae,baseline_accuracy
0,4600,2.744348,12.25913,0.123261,0.02874,0.527609,2,0.000435,2.65732,1.000000e-12,2.646457,True,9,2.686087,0.118913


,league,n,mae,mse,accuracy,macro_f1,within_two,unseen_count_rows,unseen_count_fraction,log_loss_clipped_all,log_loss_floor,log_loss_supported_only,exact_log_loss_infinite
0,Bundesliga,305,2.809836,11.885246,0.098361,0.031797,0.472131,0,0.000000,2.652081,1.000000e-12,2.652081,False
1,Bundesliga_2,306,2.852941,12.493464,0.101307,0.025858,0.480392,0,0.000000,2.652163,1.000000e-12,2.652163,False
2,Championship,552,2.759058,12.653986,0.128623,0.036592,0.523551,0,0.000000,2.641964,1.000000e-12,2.641964,False
3,Eredivisie,306,2.607843,11.405229,0.150327,0.054266,0.571895,0,0.000000,2.621019,1.000000e-12,2.621019,False
4,La_Liga,380,2.605263,11.200000,0.134211,0.037616,0.547368,1,0.002632,2.657688,1.000000e-12,2.591796,True
5,La_Liga_2,462,2.428571,9.670996,0.158009,0.048508,0.577922,0,0.000000,2.570565,1.000000e-12,2.570565,False
6,Ligue_1,306,2.745098,12.104575,0.130719,0.043160,0.516340,0,0.000000,2.640079,1.000000e-12,2.640079,False
7,Ligue_2,306,2.892157,13.741830,0.114379,0.038371,0.522876,0,0.000000,2.681936,1.000000e-12,2.681936,False
8,Premier_League,380,2.865789,13.192105,0.113158,0.036876,0.531579,0,0.000000,2.685266,1.000000e-12,2.685266,False
9,Premiership,228,2.982456,15.052632,0.127193,0.036871,0.504386,0,0.000000,2.713592,1.000000e-12,2.713592,False


,count_class,fit_count,sample_weight
0,1,14,1.0
1,2,89,1.0
2,3,268,1.0
3,4,537,1.0
4,5,880,1.0
5,6,1410,1.0
6,7,1881,1.0
7,8,2101,1.0
8,9,2247,1.0
9,10,2215,1.0


,observed_total_corners,predicted_total_corners,observed_class_probability
row_position,,,
20950,27,9,0.0
23334,26,12,0.0


class,1,2,3,4,5,6,7,8,9,10,...,16,17,18,19,20,21,22,23,24,25
row_position,,,,,,,,,,,,,,,,,,,,,
18886,0.005630,0.008325,0.014146,0.026146,0.031739,0.057504,0.080472,0.106804,0.106021,0.096114,...,0.026283,0.016385,0.017309,0.009901,0.007181,0.007747,0.005539,0.005280,0.005195,0.005058
18887,0.005689,0.010065,0.023508,0.029937,0.041705,0.068380,0.103211,0.110252,0.101849,0.131948,...,0.015272,0.018701,0.009332,0.013749,0.007330,0.007188,0.005597,0.005335,0.005249,0.005111
18888,0.005925,0.009201,0.021644,0.026276,0.041106,0.061755,0.091107,0.080712,0.100745,0.106122,...,0.024042,0.018153,0.012267,0.008540,0.009434,0.006481,0.005829,0.005556,0.005467,0.005323
18889,0.005965,0.008033,0.014266,0.026028,0.035546,0.065081,0.103714,0.094496,0.101932,0.104202,...,0.028579,0.018915,0.013205,0.008174,0.007947,0.006609,0.005868,0.005594,0.005504,0.005359
18890,0.005680,0.008026,0.015109,0.027783,0.034920,0.048716,0.085340,0.114313,0.105525,0.111458,...,0.023285,0.015437,0.013437,0.007891,0.007612,0.006245,0.005588,0.005327,0.005241,0.005103
18891,0.005942,0.009674,0.014690,0.025221,0.044818,0.062136,0.088997,0.092559,0.108022,0.096904,...,0.023760,0.017313,0.014218,0.007925,0.008813,0.006289,0.005846,0.005572,0.005483,0.005338
18892,0.005879,0.009064,0.015023,0.028177,0.040758,0.061212,0.098901,0.113160,0.126042,0.107498,...,0.019707,0.015807,0.010998,0.008139,0.008008,0.006170,0.005784,0.005513,0.005425,0.005282
18893,0.005903,0.009272,0.015245,0.025368,0.038432,0.063756,0.096454,0.104169,0.096191,0.099887,...,0.024917,0.014349,0.013795,0.008457,0.007488,0.006300,0.005807,0.005536,0.005447,0.005303
18894,0.005846,0.009929,0.019893,0.027166,0.042681,0.075930,0.095271,0.106241,0.104147,0.127805,...,0.016375,0.020163,0.010200,0.014048,0.007572,0.007330,0.005751,0.005482,0.005394,0.005252


### Most probable count versus observed count
The classifier's prediction is the most probable count class, not the probability-weighted mean. The latter is retained as a separate diagnostic column.

In [7]:
view = trial.predictions.sort_values("kickoff_at", kind="stable")
if len(view) > MAX_PLOT_MATCHES:
    view = view.iloc[np.linspace(0, len(view) - 1, MAX_PLOT_MATCHES, dtype=int)]
figure = go.Figure()
figure.add_trace(go.Scatter(x=view.kickoff_at, y=view.observed_total_corners,
    mode="markers", name="Observed count", marker=dict(color="#b6c5d8", size=5)))
figure.add_trace(go.Scatter(x=view.kickoff_at, y=view.predicted_total_corners,
    mode="markers", name="Predicted count class", marker=dict(color="#4dd4bd", size=6)))
figure.update_layout(template="plotly_dark", height=450,
    title=f"Total corners — {len(view)} held-out fixtures", xaxis_title="Kickoff (UTC)", yaxis_title="Corners")
figure.show()
figure.write_html(trial.output_path / "heldout_counts.html", include_plotlyjs=True)


### Feature gain and navigable report
Gain is a fitted-tree diagnostic, not causal influence. All input features remained eligible even if a fitted tree never split on them.

In [8]:
importance = trial.importance.head(TOP_GAIN_FEATURES)
display(importance)
if len(importance):
    figure = go.Figure(go.Bar(x=importance.gain.iloc[::-1], y=importance.feature.iloc[::-1],
        orientation="h", marker_color="#4dd4bd"))
    figure.update_layout(template="plotly_dark", height=max(450, 23 * len(importance)),
        margin=dict(l=380), title="Selected classifier: highest-gain inputs", xaxis_title="Average split gain")
    figure.show()
trial.result.show()


,feature,gain
455,away::1ST_Match overview_cornerKicks_against_lag1,13.316002
374,home::ALL_Defending_ballRecovery_against_mean10,13.308899
432,away::ALL_Match overview_cornerKicks_for_lag2,13.263580
1090,trend::home::ALL_Shots_shotsOffGoal_against_me...,13.082504
806,away::ALL_Defending_ballRecovery_against_std5,12.875183
712,away::ALL_Attack_touchesInOppBox_against_ema10,12.726562
607,away::1ST_Shots_shotsOnGoal_for_lag1,12.666641
158,home::ALL_Shots_shotsOnGoal_for_mean20,12.526324
794,away::ALL_Passes_finalThirdPhaseStatistic_agai...,12.361633
195,home::ALL_Shots_shotsOffGoal_against_lag3,12.163010


### Load the fitted model without retraining
This is a prediction round-trip on the already prepared feature table. Future fixtures need the same feature definitions and column order; loading a model does not construct those histories automatically.

In [9]:
saved_path = Path(json.loads((trial.output_path / "summary.json").read_text())["model_path"])
if saved_path.exists():
    fitted_model = load_model(saved_path)
    saved_predictions = fitted_model.predict(trial.result.dataset)
    heldout = trial.predictions.index
    np.testing.assert_array_equal(saved_predictions["predict"].loc[heldout].iloc[:, 0],
                                  trial.predictions.predicted_total_corners)
    print("Saved-model prediction parity verified.")
else:
    print("This reused result has retained predictions but no separately saved model.")


Saved-model prediction parity verified.


## Next steps
Compare MAE, exact accuracy, ±2 coverage and class support against the majority-count baseline and previous experiments. Weighting can improve rare-class treatment while worsening overall error; use the untouched test results to describe this run, not to retune it repeatedly. This notebook does not fit a probability calibrator or automatically turn class probabilities into betting decisions.